## Test de trajectoires des navires de pêche présents dans le parc 

Hypothèse testée: Des bateaux de pêche éteignent leur AIS dans le parc?

Type de bateaux: pêche palangrière

In [40]:
import os
import numpy as np

import pandas as pd
import geopandas as gpd

import datetime
import time

import matplotlib.pyplot as plt
import seaborn as sns
import folium

import re
from html import escape
import colorsys

In [41]:
# load the data path
os.chdir('C:/Users/anael/Documents/PNMCCA_Marbec_2026/traj_bateaux_PNMCCA/')

## Trajectoires GFW
### bateaux identifié sur GFW directement
Bateaux de pêche (palangriers) qui font au moins un passage à un moment t dans le parc marin (pêche ou non).

- Italia II > 2024
- Madonna del Carmine > 2022-2026
- Madonna di Fatima > 2023
- Ammiraglia > 2023
- ct2895 > 2022

### Bateaux ajouté à partir des données AIS 2025 fournit par le parc
2 bateaux ajoutés (palangriers). 

- Pablo I > 2024-2026
- Feli > 2025-2026

Madonna del Carmine bien pésent dans leur données aussi. 6 bateaux de pêches présents dans les données AIS du parc mais pas inclus ici car pas palangriers (chalutier ou senner), traverse juste une ou deux fois le parc, ou mauvaise classif (bateaux de loisir, fishery research vessel).

In [42]:
# navires trouvé à partir de GFW uniquement 
ammiraglia = pd.read_csv('./raw_traj_GFW/ammiraglia-2023-2024.csv')
ct2895 = pd.read_csv('./raw_traj_GFW/ct2895-2022.csv')
italiaII = pd.read_csv('./raw_traj_GFW/italiaII-2023.csv')
madonnadelcarmine = pd.read_csv('./raw_traj_GFW/madonnadelcarmine-2022-2026.csv')
madonnadifatima = pd.read_csv('./raw_traj_GFW/madonnadifatima-2023.csv')

# 2 navires ajourter suite grâce aux détections AIS fournit par le parc + traj de GFW
feli = pd.read_csv('./raw_traj_GFW/feli-2025-2026.csv')
pabloI = pd.read_csv('./raw_traj_GFW/pabloI-2024-2026.csv')

In [43]:
ais_data_list = [ammiraglia, ct2895, italiaII, madonnadelcarmine, madonnadifatima, feli, pabloI]

In [44]:
ais_data_list[0]

,lon,lat,course,timestamp,speed,depth,seg_id
0,15.800467,38.315630,319.799988,2023-01-03T03:55:48.000Z,7.8,-414,247133620-2023-01-03T03:55:48.000000Z-1
1,15.747247,38.355190,308.799988,2023-01-03T04:19:36.000Z,8.7,-358,247133620-2023-01-03T03:55:48.000000Z-1
2,15.719147,38.382538,320.000000,2023-01-03T04:34:37.000Z,8.3,-438,247133620-2023-01-03T03:55:48.000000Z-1
3,15.687755,38.407688,316.299988,2023-01-03T04:49:47.000Z,8.2,-459,247133620-2023-01-03T03:55:48.000000Z-1
4,15.620213,38.445623,272.700012,2023-01-03T05:37:56.000Z,1.6,-627,247133620-2023-01-03T03:55:48.000000Z-1
...,...,...,...,...,...,...,...
7983,15.722483,38.391087,149.699997,2023-12-29T15:00:41.000Z,6.1,-440,247133620-2023-12-27T03:55:41.000000Z-1
7984,15.740368,38.370843,142.300003,2023-12-29T15:14:32.000Z,8.0,-363,247133620-2023-12-27T03:55:41.000000Z-1
7985,15.791050,38.319625,141.000000,2023-12-29T15:41:02.000Z,9.0,-436,247133620-2023-12-27T03:55:41.000000Z-1
7986,15.803427,38.308580,135.000000,2023-12-29T15:47:11.000Z,8.7,-362,247133620-2023-12-27T03:55:41.000000Z-1


In [45]:
# formater la colonne timestamp en format date-heure
#calculer le temps écouler entre deux lignes (2 points AIS)
for i in np.arange(7):
    ais_data_list[i].loc[: ,'timestamp'] = pd.to_datetime(ais_data_list[i].timestamp)
    ais_data_list[i]["T"] = ais_data_list[i]["timestamp"].diff()
    ais_data_list[i]["T_hour"] = ais_data_list[i]["T"].dt.total_seconds() / 3600

In [46]:
ais_data_list[0]

,lon,lat,course,timestamp,speed,depth,seg_id,T,T_hour
0,15.800467,38.315630,319.799988,2023-01-03 03:55:48+00:00,7.8,-414,247133620-2023-01-03T03:55:48.000000Z-1,NaT,NaN
1,15.747247,38.355190,308.799988,2023-01-03 04:19:36+00:00,8.7,-358,247133620-2023-01-03T03:55:48.000000Z-1,0 days 00:23:48,0.396667
2,15.719147,38.382538,320.000000,2023-01-03 04:34:37+00:00,8.3,-438,247133620-2023-01-03T03:55:48.000000Z-1,0 days 00:15:01,0.250278
3,15.687755,38.407688,316.299988,2023-01-03 04:49:47+00:00,8.2,-459,247133620-2023-01-03T03:55:48.000000Z-1,0 days 00:15:10,0.252778
4,15.620213,38.445623,272.700012,2023-01-03 05:37:56+00:00,1.6,-627,247133620-2023-01-03T03:55:48.000000Z-1,0 days 00:48:09,0.802500
...,...,...,...,...,...,...,...,...,...
7983,15.722483,38.391087,149.699997,2023-12-29 15:00:41+00:00,6.1,-440,247133620-2023-12-27T03:55:41.000000Z-1,0 days 00:24:20,0.405556
7984,15.740368,38.370843,142.300003,2023-12-29 15:14:32+00:00,8.0,-363,247133620-2023-12-27T03:55:41.000000Z-1,0 days 00:13:51,0.230833
7985,15.791050,38.319625,141.000000,2023-12-29 15:41:02+00:00,9.0,-436,247133620-2023-12-27T03:55:41.000000Z-1,0 days 00:26:30,0.441667
7986,15.803427,38.308580,135.000000,2023-12-29 15:47:11+00:00,8.7,-362,247133620-2023-12-27T03:55:41.000000Z-1,0 days 00:06:09,0.102500


## Tester sur ces bateaux l'hypothèse de coupure d'AIS 
Localiser les coupures d'AIS: points AIS espacé de 3h ou plus

In [49]:
# selectionné les lignes où l'écart des timestamp est supérieur à 24h.
ais_ecarts3h_list = []

for i in range(7):
    values_list = []
    df = ais_data_list[i].copy()
    mask = df['T_hour'] > 3
    indices = df.index[mask]# Indices des lignes qui remplissent la condition

    for idx in indices:     
        pos = df.index.get_loc(idx)# Position de la ligne dans le DataFrame
        if pos > 0:
            T_hour = df.iloc[pos]['T_hour']
            timestamp_A = df.iloc[pos-1]['timestamp']
            timestamp_B = df.iloc[pos]['timestamp']
            
            lon_A = df.iloc[pos]['lon']
            lat_A = df.iloc[pos]['lat']
            course_A = df.iloc[pos]['course']
            speed_A = df.iloc[pos]['speed']
            depth_A = df.iloc[pos]['depth']

            lon_B = df.iloc[pos-1]['lon']
            lat_B = df.iloc[pos-1]['lat']
            course_B = df.iloc[pos-1]['course']
            speed_B = df.iloc[pos-1]['speed']
            depth_B = df.iloc[pos-1]['depth']

            values_list.append((T_hour, timestamp_A, timestamp_B, 
                                lon_A, lat_A, course_A, speed_A, depth_A,
                               lon_B, lat_B, course_B, speed_B, depth_B,))
    ais_ecarts= pd.DataFrame(values_list, columns=['T_hour', 'timestamp_A', 'timestamp_B', 
                                                   'lon_A', 'lat_A', 'course_A', 'speed_A', 'depth_A',
                                                  'lon_B', 'lat_B', 'course_B', 'speed_B', 'depth_B']) # df 
    ais_ecarts3h_list.append(ais_ecarts)

In [106]:
# Mapper les deux points AIS en question (permet de voir où se produire ces potentielles coupures d'AIS: au port ou en mer...)
map3h_list = []
CARTO_API_KEY = "cb1_4uyn_1_dfa047c0e6c9462ab0eba889"
list_names = ["ammiraglia", "ct2895", "italiaII", "madonnadelcarmine", "madonnadifatima", "feli", "pabloI"]

parc = gpd.read_file(
    r"contours_parc\WDPA_WDOECM_Oct2026_Public_555561929_shp-polygons.shp"
) # check préalable des crs (ok)


for num_bateau in range(7): 
    df = ais_ecarts3h_list[num_bateau].copy()
    
    # Vérifier les coordonnées disponibles
    all_lats = pd.concat([df["lat_A"], df["lat_B"]]).dropna()
    all_lons = pd.concat([df["lon_A"], df["lon_B"]]).dropna()
    
    m = folium.Map(
        location=[all_lats.mean(), all_lons.mean()],
        zoom_start=12,
        tiles=None
    )
    
    folium.TileLayer(
    tiles=(
        "https://basemaps.cartocdn.com/"
        "rastertiles/light_all/{z}/{x}/{y}.png"
        f"?key={CARTO_API_KEY}"
    ),
    attr='© OpenStreetMap contributors © CARTO',
    name="CARTO Positron",
    max_zoom=20
    ).add_to(m)

    folium.GeoJson(
        parc,
        name="Parc naturel marin du Cap Corse et de l'Agriate",
        style_function=lambda feature: {
            "color": "#00A6A6",
            "weight": 3,
            "fill": False,
            "opacity": 1
        },
        tooltip="Parc naturel marin du Cap Corse et de l'Agriate"
    ).add_to(m)
    
    # Générer une couleur par catégorie de T_hour
    def get_color(T_hour):
        if pd.isna(T_hour):
            return "#808080"  # Gris : valeur manquante
        elif 3 <= T_hour < 6:
            return "#2E8B57"  # Vert : 3 à moins de 6 h
        elif 6 <= T_hour <= 24:
            return "#E6A23C"  # Orange : 6 à 24 h
        elif T_hour > 24:
            return "#D64545"  # Rouge : plus de 24 h
        else:
            return "#808080"  # Gris : moins de 3 h
 
    
    
    # Colonnes propres à chaque point
    cols_A = [c for c in df.columns if c.endswith("_A")]
    cols_B = [c for c in df.columns if c.endswith("_B")]
    
    def create_popup(row, cols, suffix, color):
        # T_hour est ajouté même s'il ne possède pas de suffixe
        html = f"""
        <div style="font-family: Arial; min-width: 220px;">
            <h4 style="color: {color}; margin-bottom: 8px;">
                Paire {row.name} — Point {suffix}
            </h4>
            <table style="border-collapse: collapse; width: 100%;">
        """
    
        # Afficher T_hour en premier
        fields = ["T_hour"] + [c for c in cols if c != "T_hour"]
    
        for col in fields:
            if col not in row.index:
                continue
    
            label = col[:-2] if col.endswith(("_A", "_B")) else col
            value = escape(str(row[col]))
    
            html += f"""
            <tr>
                <td style="padding: 4px; border-bottom: 1px solid #ddd;">
                    <b>{escape(label)}</b>
                </td>
                <td style="padding: 4px; border-bottom: 1px solid #ddd;">
                    {value}
                </td>
            </tr>
            """
    
        html += "</table></div>"
        return folium.Popup(html, max_width=400)
    
    # Ajouter les marqueurs avec des formes différentes pour A et B
    for idx, row in df.iterrows():
        color = get_color(row["T_hour"])
    
        # Point B : cercle
        if pd.notna(row["lat_B"]) and pd.notna(row["lon_B"]):
            folium.CircleMarker(
                location=[row["lat_B"], row["lon_B"]],
                radius=7,
                color=color,
                fill=True,
                fill_color=color,
                fill_opacity=0.85,
                weight=2,
                tooltip=f"Paire {idx} — Point B | T_hour: {row['T_hour']}",
                popup=create_popup(row, cols_B, "B", color)
            ).add_to(m)
    
        # Point A : triangle
        if pd.notna(row["lat_A"]) and pd.notna(row["lon_A"]):
            folium.RegularPolygonMarker(
                location=[row["lat_A"], row["lon_A"]],
                number_of_sides=3,
                radius=9,
                rotation=0,
                color=color,
                fill=True,
                fill_color=color,
                fill_opacity=0.85,
                tooltip=f"Paire {idx} — Point A | T_hour: {row['T_hour']}",
                popup=create_popup(row, cols_A, "A", color)
            ).add_to(m)
        # Relier les points A et B de chaque paire
        if (
            pd.notna(row["lat_A"]) and pd.notna(row["lon_A"])
            and pd.notna(row["lat_B"]) and pd.notna(row["lon_B"])
        ):
            folium.PolyLine(
                locations=[
                    [row["lat_A"], row["lon_A"]],
                    [row["lat_B"], row["lon_B"]]
                ],
                color=color,
                weight=2,
                opacity=0.7,
                tooltip=f"Paire {idx} — T_hour: {row['T_hour']}"
            ).add_to(m)
    # Adapter le cadrage à tous les points valides
    points = []
    for _, row in df.iterrows():
        for lat_col, lon_col in [
            ("lat_A", "lon_A"),
            ("lat_B", "lon_B")
        ]:
            if pd.notna(row[lat_col]) and pd.notna(row[lon_col]):
                points.append([row[lat_col], row[lon_col]])
    
    if points:
        m.fit_bounds(points)


    # legend 
    legend_html = f"""
    <div style="
        position: fixed;
        bottom: 30px;
        left: 30px;
        z-index: 9999;
        background-color: white;
        padding: 12px 15px;
        border: 1px solid #999;
        border-radius: 6px;
        font-size: 13px;
        font-family: Arial;
    ">
        <b>Bateau : {list_names[num_bateau]}</b><br>
        <hr style="margin: 6px 0;">
        <b>Durée de coupure AIS</b><br>

        <span style="color:#2E8B57;">●</span> 3 h ≤ T &lt; 6 h<br>
        <span style="color:#E6A23C;">●</span> 6 h ≤ T ≤ 24 h<br>
        <span style="color:#D64545;">●</span> T &gt; 24 h
    </div>
    """
    
    m.get_root().html.add_child(folium.Element(legend_html))

    map3h_list.append(m)


# Cartographies des potentielles coupures d'AIS

Visualisation des cartes : 1 carte par navire, représentant les paires de points AIS successifs espacés de >3h (les potentielles coupures d'AIS).

🔷 Triangle = Point A : localisation du premier point de la paire.

🔵 Cercle  = Point B : localisation du second point de la paire.

Ces deux points sont reliés par une ligne.
La couleur de chaque paire dépande de la durée séparant les deux points AIS (durée de la coupure)
- points AIS espacé de 24h ou plus
- points AIS espacé de 6h à 24h
- points AIS espacé de 3h à 6h

<u>Informations interactives<u>

Survol d'un marqueur : affiche l'identifiant de la paire, le type de point (A ou B) et la valeur de T_hour qui est la durée entre les deux points AIS successifs.

Clic sur un marqueur : ouvre une fenêtre contenant les informations associées au point: date, coordonnées, cap, vitesse.

Survol d'une ligne : affiche l'identifiant de la paire et la valeur de T_hour.


In [107]:
display(map3h_list[0])

In [108]:
display(map3h_list[1])

In [109]:
display(map3h_list[2])

In [113]:
display(map3h_list[3])

In [110]:
display(map3h_list[4])

In [101]:
display(map3h_list[5])

In [111]:
display(map3h_list[6])

In [112]:
dossier = 'C:\\Users\\anael\\Documents\\PNMCCA_Marbec_2026'

map3h_list[0].save(os.path.join(dossier, "map3h_1.html"))
map3h_list[1].save(os.path.join(dossier, "map3h_2.html"))
map3h_list[2].save(os.path.join(dossier, "map3h_3.html"))
map3h_list[3].save(os.path.join(dossier, "map3h_4.html"))
map3h_list[4].save(os.path.join(dossier, "map3h_5.html"))
map3h_list[5].save(os.path.join(dossier, "map3h_6.html"))
map3h_list[6].save(os.path.join(dossier, "map3h_7.html"))

## Conclusions & Limites

Certains bateaux ont des coupures proches du parc:
- Amiraglia (juste 1)
- ct2895
- Madonna del Carmine
- Pablo I

Les autres qui ne présentent aucun signes de coupure dans notre zone d'étude, à écarter des analyses suivantes ?
- Feli
- Madonna di Fatima
- Italia II


**Limites: Difficiles de savoir l'origine de l'interuption de la transmission de l'AIS**

Les coupures AIS autour du Cap Corse et dans la mer Ligure peuvent avoir plusieurs origines :
- une émission AIS réellement interrompue ;
- une réception satellite perturbée par le trafic maritime dense ;
- une transition entre couverture terrestre et couverture satellite ;
- des différences entre les sources de données intégrées à GFW.

Noter que GFW intègre les données de Marine Traffic à partir du 3 janvier 2024.

**TO DO ?**
Faire les mêmes cartes avec les données AIS réelles (pas GFW) avec un unique fournisseur pour voir si on retrouve les mêmes coupures et donc écarter celles qui seraient due au processing des données fait par GFW. 

# Exploration des coupures "suspectes"

Selection des coupures potentielles près du parc et exploration de l'activité du bateau les jours d'avant et d'après (trajectoire, pêche).

Selection à la main des coupures 'suspectes' pour les 4 navires mentionnés ci-dessus.

In [114]:
ais_ecarts3h_list[0]

,T_hour,timestamp_A,timestamp_B,lon_A,lat_A,course_A,speed_A,depth_A,lon_B,lat_B,course_B,speed_B,depth_B
0,29.231389,2023-01-03 15:17:08+00:00,2023-01-04 20:31:01+00:00,15.806912,38.300803,262.000000,7.1,-80,15.814805,38.300000,223.899994,3.2,-80
1,1340.867778,2023-01-05 09:39:03+00:00,2023-03-02 06:31:07+00:00,15.217625,36.770842,27.299999,9.4,-115,15.126350,36.671593,0.000000,0.0,3
2,80.896111,2023-03-02 18:47:13+00:00,2023-03-06 03:40:59+00:00,15.810322,38.303263,289.100006,4.9,-80,15.814040,38.298867,67.300003,0.4,-80
3,33.298056,2023-03-06 17:41:15+00:00,2023-03-08 02:59:08+00:00,15.813105,38.301713,287.399994,3.5,-80,15.789893,38.320150,139.800003,8.8,-436
4,9.461389,2023-03-08 17:42:58+00:00,2023-03-09 03:10:39+00:00,15.813352,38.299115,44.400002,0.2,-80,15.785170,38.307697,100.199997,7.4,-389
...,...,...,...,...,...,...,...,...,...,...,...,...,...
130,10.160833,2023-12-20 17:49:56+00:00,2023-12-21 03:59:35+00:00,15.808988,38.305712,316.200012,6.4,-289,15.814575,38.299775,224.000000,4.2,-80
131,38.242778,2023-12-21 17:53:29+00:00,2023-12-23 08:08:03+00:00,15.813718,38.299147,78.400002,2.2,-80,15.808835,38.306700,130.500000,7.8,-289
132,88.054167,2023-12-23 11:52:26+00:00,2023-12-27 03:55:41+00:00,15.813892,38.301912,298.799988,5.1,-80,15.815293,38.301850,165.000000,6.4,196
133,9.812500,2023-12-27 17:51:13+00:00,2023-12-28 03:39:58+00:00,15.814643,38.299835,51.000000,4.1,-80,15.813025,38.303188,124.000000,8.4,-80


In [115]:
ais_data_list[0]

,lon,lat,course,timestamp,speed,depth,seg_id,T,T_hour
0,15.800467,38.315630,319.799988,2023-01-03 03:55:48+00:00,7.8,-414,247133620-2023-01-03T03:55:48.000000Z-1,NaT,NaN
1,15.747247,38.355190,308.799988,2023-01-03 04:19:36+00:00,8.7,-358,247133620-2023-01-03T03:55:48.000000Z-1,0 days 00:23:48,0.396667
2,15.719147,38.382538,320.000000,2023-01-03 04:34:37+00:00,8.3,-438,247133620-2023-01-03T03:55:48.000000Z-1,0 days 00:15:01,0.250278
3,15.687755,38.407688,316.299988,2023-01-03 04:49:47+00:00,8.2,-459,247133620-2023-01-03T03:55:48.000000Z-1,0 days 00:15:10,0.252778
4,15.620213,38.445623,272.700012,2023-01-03 05:37:56+00:00,1.6,-627,247133620-2023-01-03T03:55:48.000000Z-1,0 days 00:48:09,0.802500
...,...,...,...,...,...,...,...,...,...
7983,15.722483,38.391087,149.699997,2023-12-29 15:00:41+00:00,6.1,-440,247133620-2023-12-27T03:55:41.000000Z-1,0 days 00:24:20,0.405556
7984,15.740368,38.370843,142.300003,2023-12-29 15:14:32+00:00,8.0,-363,247133620-2023-12-27T03:55:41.000000Z-1,0 days 00:13:51,0.230833
7985,15.791050,38.319625,141.000000,2023-12-29 15:41:02+00:00,9.0,-436,247133620-2023-12-27T03:55:41.000000Z-1,0 days 00:26:30,0.441667
7986,15.803427,38.308580,135.000000,2023-12-29 15:47:11+00:00,8.7,-362,247133620-2023-12-27T03:55:41.000000Z-1,0 days 00:06:09,0.102500
